# Textual Embeddings for StarkQA-PrimeKG using nomic-embed-text

In this tutorial, we will perform textual (enrichment and) embeddings for StarkQA-PrimeKG and eventually construct a knowledge graph.

First of all, we need to import necessary libraries as follows:

In [1]:
# Import necessary libraries
import os
import pickle
import sys

from torch_geometric.utils import from_networkx
from tqdm import tqdm

sys.path.append("../../..")
from phronesis.synapta.datasets.primekg import PrimeKG
from phronesis.synapta.datasets.starkqa_primekg import StarkQAPrimeKG
from phronesis.synapta.utils import kg_utils
from phronesis.synapta.utils.embeddings.sentence_transformer import (
    EmbeddingWithSentenceTransformer,
)

# # Set the logging level for httpx to WARNING to suppress INFO messages
# import logging
# logging.getLogger("httpx").setLevel(logging.WARNING)

/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm
/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/pydantic/_internal/_fields.py:132: UserWarning: Field "model_id" in SysBioModel has conflict with protected namespace "model_".

You may be able to resolve this warning by setting `model_config['protected_namespaces'] = ()`.
  warnings.warn(
/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/pydantic/_internal/_fields.py:132: UserWarning: Field "model_id" in BasicoModel has conflict with protected namespace "model_".

You may be able to resolve this warning by setting `model_config['protected_namespaces'] = ()`.
  warnings.warn(
/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-

We need to load the PrimeKG and StarkQAPrimeKG datasets in order to construct the knowledge graph for later application.

### Load PrimeKG

To load PrimeKG dataset, we can utilize the `PrimeKG` class from the phronesis/synapta library.

The `PrimeKG` needs to be initialized with the path to the PrimeKG dataset to be stored/loaded from the local directory.

In [2]:
# Define primekg data by providing a local directory where the data is stored
primekg_data = PrimeKG(local_dir="../../../../data/primekg/")

# Invoke a method to load the data
primekg_data.load_data()

# Get primekg_nodes and primekg_edges
primekg_nodes = primekg_data.get_nodes()
primekg_edges = primekg_data.get_edges()

Loading nodes of PrimeKG dataset ...
../../../../data/primekg/primekg_nodes.tsv.gz already exists. Loading the data from the local directory.
Loading edges of PrimeKG dataset ...
../../../../data/primekg/primekg_edges.tsv.gz already exists. Loading the data from the local directory.


We can check the dataframes of nodes and edges of PrimeKG as follows:

In [3]:
# Check PrimeKG nodes
primekg_nodes.head()

,node_index,node_name,node_source,node_id,node_type
0,0,PHYHIP,NCBI,9796,gene/protein
1,1,GPANK1,NCBI,7918,gene/protein
2,2,ZRSR2,NCBI,8233,gene/protein
3,3,NRF1,NCBI,4899,gene/protein
4,4,PI4KA,NCBI,5297,gene/protein


In [4]:
# Check PrimeKG edges
primekg_edges.head()

,head_index,head_name,head_source,head_id,head_type,tail_index,tail_name,tail_source,tail_id,tail_type,display_relation,relation
0,0,PHYHIP,NCBI,9796,gene/protein,8889,KIF15,NCBI,56992,gene/protein,ppi,protein_protein
1,1,GPANK1,NCBI,7918,gene/protein,2798,PNMA1,NCBI,9240,gene/protein,ppi,protein_protein
2,2,ZRSR2,NCBI,8233,gene/protein,5646,TTC33,NCBI,23548,gene/protein,ppi,protein_protein
3,3,NRF1,NCBI,4899,gene/protein,11592,MAN1B1,NCBI,11253,gene/protein,ppi,protein_protein
4,4,PI4KA,NCBI,5297,gene/protein,2122,RGS20,NCBI,8601,gene/protein,ppi,protein_protein


### Load StarkQA

In [5]:
# Define starkqa primekg data by providing a local directory where the data is stored
starkqa_data = StarkQAPrimeKG(local_dir="../../../../data/starkqa_primekg/")

# Invoke a method to load the data
starkqa_data.load_data()

# Get the StarkQAPrimeKG data, which are the QA pairs, split indices, and the node information
starkqa_df = starkqa_data.get_starkqa()
starkqa_split_indices = starkqa_data.get_starkqa_split_indicies()
starkqa_node_info = starkqa_data.get_starkqa_node_info()

Loading StarkQAPrimeKG dataset...
../../../../data/starkqa_primekg/qa/prime/stark_qa/stark_qa.csv already exists. Loading the data from the local directory.
Loading StarkQAPrimeKG embeddings...


/home/awmulyadi/Repositories/office/Phronesis/docs/notebooks/synapta/../../../phronesis/synapta/datasets/starkqa_primekg.py:141: FutureWarning: You are using `torch.load` with `weights_only=False` (the current default value), which uses the default pickle module implicitly. It is possible to construct malicious pickle data which will execute arbitrary code during unpickling (See https://github.com/pytorch/pytorch/blob/main/SECURITY.md#untrusted-models for more details). In a future release, the default value for `weights_only` will be flipped to `True`. This limits the functions that could be executed during unpickling. Arbitrary objects will no longer be allowed to be loaded via this mode unless they are explicitly allowlisted by the user via `torch.serialization.add_safe_globals`. We recommend you start setting `weights_only=True` for any use case where you don't have full control of the loaded file. Please open an issue on GitHub for any issues related to this experimental feature.


We can get a set of questions from the StarkQA dataset contained in `starkqa_df`

In [6]:
# Check StarkQA data
starkqa_df.head()

,id,query,answer_ids
0,0,Could you identify any skin diseases associate...,[95886]
1,1,What drugs target the CYP3A4 enzyme and are us...,[15450]
2,2,What is the name of the condition characterize...,"[98851, 98853]"
3,3,What drugs are used to treat epithelioid sarco...,[15698]
4,4,Can you supply a compilation of genes and prot...,"[7161, 22045]"


Within the `starkqa_node_info` dictionary, we can access additional information of the nodes in the PrimeKG dataset provided by StarkQA team.

In [7]:
# We can obtain additional node information from StarkQAPrimeKG
starkqa_node_info[0]

{'id': 9796,
 'type': 'gene/protein',
 'name': 'PHYHIP',
 'source': 'NCBI',
 'details': {'query': 'PHYHIP',
  '_id': '9796',
  '_score': 17.934021,
  'alias': ['DYRK1AP3', 'PAHX-AP', 'PAHXAP1'],
  'genomic_pos': {'chr': '8',
   'end': 22232101,
   'ensemblgene': 'ENSG00000168490',
   'start': 22219703,
   'strand': -1},
  'name': 'phytanoyl-CoA 2-hydroxylase interacting protein',
  'summary': 'Enables protein tyrosine kinase binding activity. Involved in protein localization. Located in cytoplasm. [provided by Alliance of Genome Resources, Apr 2022]'}}

### Textual Enrichment over PrimeKG

We begin with the textual enrichment over the PrimeKG nodes by using the StarkQA node information.

Note that not all nodes in the PrimeKG have additional information. For this case, we provide a basic text enrichment for the nodes by simply specifying their node name and type.

In [8]:
def enrich_node(data, node_info):
    """
    Enrich the node with additional information from StarkQA-PrimeKG

    Args:
        data (dict): The node data from PrimeKG
        node_info (dict): The node information from StarkQA-PrimeKG
    """
    # Basic textual enrichment of the node
    enriched_node = f"{data['node_name']} belongs to {data['node_type']} category. "
    # Only enrich the node if the node type is gene/protein, drug, disease, or pathway, which
    # has additional information in the node_info of StarkQA-PrimeKG
    added_info = ""
    if data["node_type"] == "gene/protein":
        added_info = (
            node_info["details"]["summary"] if "summary" in node_info["details"] else ""
        )
    elif data["node_type"] == "drug":
        added_info = " ".join(
            [
                str(node_info["details"]["description"]).replace("nan", ""),
                str(node_info["details"]["mechanism_of_action"]).replace("nan", ""),
                str(node_info["details"]["protein_binding"]).replace("nan", ""),
                str(node_info["details"]["pharmacodynamics"]).replace("nan", ""),
                str(node_info["details"]["indication"]).replace("nan", ""),
            ]
        )
    elif data["node_type"] == "disease":
        added_info = " ".join(
            [
                str(node_info["details"]["mondo_definition"]).replace("nan", ""),
                str(node_info["details"]["mayo_symptoms"]).replace("nan", ""),
                str(node_info["details"]["mayo_causes"]).replace("nan", ""),
            ]
        )
    elif data["node_type"] == "pathway":
        added_info += (
            f"This pathway found in {node_info['details']['speciesName']}. "
            + " ".join([x["text"] for x in node_info["details"]["summation"]])
            if "details" in node_info
            else ""
        )
    # Append the additional information for enrichment
    enriched_node += added_info
    return enriched_node

By using the above function, we can enrich the node information from PrimeKG with additional information from StarkQA-PrimeKG as shown below:

In [9]:
# Perform node enrichment for each row in primekg_nodes
enriched_nodes = primekg_nodes.apply(
    lambda x: enrich_node(x, starkqa_node_info[x["node_index"]]), axis=1
).tolist()
primekg_nodes["enriched_node"] = enriched_nodes
primekg_nodes.head()

,node_index,node_name,node_source,node_id,node_type,enriched_node
0,0,PHYHIP,NCBI,9796,gene/protein,PHYHIP belongs to gene/protein category. Enabl...
1,1,GPANK1,NCBI,7918,gene/protein,GPANK1 belongs to gene/protein category. This ...
2,2,ZRSR2,NCBI,8233,gene/protein,ZRSR2 belongs to gene/protein category. This g...
3,3,NRF1,NCBI,4899,gene/protein,NRF1 belongs to gene/protein category. This ge...
4,4,PI4KA,NCBI,5297,gene/protein,PI4KA belongs to gene/protein category. This g...


Subsequently, we can perform similar textual enrichment for the edges in PrimeKG.

Since StarkQA only provides node information, we can only enrich the edges with basic information of the triples in combination with the head and tail nodes.

In [10]:
# Perform textual enrichment over the edges by simply concatenating the head and tail nodes with the relation followed by the enriched node information
enriched_edges = primekg_edges.apply(
    lambda x: f"{x['head_name']} ({x['head_type']}) has a direct relationship of {x['display_relation']} with {x['tail_name']} ({x['tail_type']}).",
    axis=1,
).tolist()
enriched_edges

['PHYHIP (gene/protein) has a direct relationship of ppi with KIF15 (gene/protein).',
 'GPANK1 (gene/protein) has a direct relationship of ppi with PNMA1 (gene/protein).',
 'ZRSR2 (gene/protein) has a direct relationship of ppi with TTC33 (gene/protein).',
 'NRF1 (gene/protein) has a direct relationship of ppi with MAN1B1 (gene/protein).',
 'PI4KA (gene/protein) has a direct relationship of ppi with RGS20 (gene/protein).',
 'SLC15A1 (gene/protein) has a direct relationship of ppi with RTL8C (gene/protein).',
 'EIF3I (gene/protein) has a direct relationship of ppi with PAXIP1 (gene/protein).',
 'FAXDC2 (gene/protein) has a direct relationship of ppi with SLC10A6 (gene/protein).',
 'MT1A (gene/protein) has a direct relationship of ppi with TP53 (gene/protein).',
 'SORT1 (gene/protein) has a direct relationship of ppi with PALMD (gene/protein).',
 'LRP5 (gene/protein) has a direct relationship of ppi with FOXP3 (gene/protein).',
 'RPS8 (gene/protein) has a direct relationship of ppi with 

In [11]:
# # For more detailed information, we can include head and tail node information in the enriched edge
# enriched_heads = primekg_edges.join(primekg_nodes.set_index('node_index'), on='head_index')[['enriched_node']].values.flatten().tolist()
# enriched_tails = primekg_edges.join(primekg_nodes.set_index('node_index'), on='tail_index')[['enriched_node']].values.flatten().tolist()

# # Concatenate the enriched head and tail nodes with the enriched edge
# mini_batch_size = 10000
# enriched_edges_final = []
# for i in tqdm(range(0, len(enriched_edges), mini_batch_size)):
#     outputs = [f"{head} {edge} {tail}" for head, edge, tail in zip(enriched_heads[i:i+mini_batch_size], enriched_edges[i:i+mini_batch_size], enriched_tails[i:i+mini_batch_size])]
#     enriched_edges_final.extend(outputs)
# enriched_edges_final

In [12]:
# Check the enriched edges
# primekg_edges['enriched_edge'] = enriched_edges_final
primekg_edges["enriched_edge"] = enriched_edges
primekg_edges.head()

,head_index,head_name,head_source,head_id,head_type,tail_index,tail_name,tail_source,tail_id,tail_type,display_relation,relation,enriched_edge
0,0,PHYHIP,NCBI,9796,gene/protein,8889,KIF15,NCBI,56992,gene/protein,ppi,protein_protein,PHYHIP (gene/protein) has a direct relationshi...
1,1,GPANK1,NCBI,7918,gene/protein,2798,PNMA1,NCBI,9240,gene/protein,ppi,protein_protein,GPANK1 (gene/protein) has a direct relationshi...
2,2,ZRSR2,NCBI,8233,gene/protein,5646,TTC33,NCBI,23548,gene/protein,ppi,protein_protein,ZRSR2 (gene/protein) has a direct relationship...
3,3,NRF1,NCBI,4899,gene/protein,11592,MAN1B1,NCBI,11253,gene/protein,ppi,protein_protein,NRF1 (gene/protein) has a direct relationship ...
4,4,PI4KA,NCBI,5297,gene/protein,2122,RGS20,NCBI,8601,gene/protein,ppi,protein_protein,PI4KA (gene/protein) has a direct relationship...


### Textual Embedding over PrimeKG

We can perform embedding using the enriched nodes and edges using `EmbeddingWithSentenceTransformer` class.

Here we will use `nomic-ai/nomic-embed-text` provided by HuggingFace via `sentence_transformer` library to embed the enriched nodes and edges.

In short, the model `nomic-ai/nomic-embed-text` requires us to add pre-fix as follows:
- `search_document: <text here>` for embedding texts as documents, for example as documents for a RAG index.
- `search_query: <text here>` for embedding texts as questions that documents from a dataset could resolve, for example as queries to be answered by a RAG application.

For more detailed information on this embedding model, please refer to the documentation:
- https://huggingface.co/nomic-ai/nomic-embed-text-v1.5


In [13]:
# Using nomic-ai/nomic-embed-text-v1.5 model with half precision for faster embedding
emb_model = EmbeddingWithSentenceTransformer(
    model_name="nomic-ai/nomic-embed-text-v1.5",
    model_cache_dir="../../../../data/nomic-ai/nomic-embed-text-v1.5/",
    trust_remote_code=True,
)

INFO:sentence_transformers.SentenceTransformer:Use pytorch device_name: cuda
INFO:sentence_transformers.SentenceTransformer:Load pretrained SentenceTransformer: nomic-ai/nomic-embed-text-v1.5


#### Query Embedding

Load the pre-processed embeddings, if available.

In [8]:
# # # Load the enriched nodes dataframe from parquet file
# starkqa_df = pd.read_parquet(os.path.join(starkqa_data.local_dir, 'starkqaprimekg_queries_embedded.parquet'), engine='pyarrow')

# # Check the dataframe of query embeddings
# starkqa_df.head()

,node_index,node_name,node_source,node_id,node_type,enriched_node
0,0,PHYHIP,NCBI,9796,gene/protein,PHYHIP belongs to gene/protein category. Enabl...
1,1,GPANK1,NCBI,7918,gene/protein,GPANK1 belongs to gene/protein category. This ...
2,2,ZRSR2,NCBI,8233,gene/protein,ZRSR2 belongs to gene/protein category. This g...
3,3,NRF1,NCBI,4899,gene/protein,NRF1 belongs to gene/protein category. This ge...
4,4,PI4KA,NCBI,5297,gene/protein,PI4KA belongs to gene/protein category. This g...


If there is no pre-processed query embeddings, run the following codes to generate embeddings.

Otherwise, skip the following cells and go to `Node Embedding`.

In [14]:
# Prepend prefix to the query
starkqa_df["query_prefixed"] = starkqa_df["query"].apply(lambda x: f"search_query: {x}")
starkqa_df.head()

,id,query,answer_ids,query_prefixed
0,0,Could you identify any skin diseases associate...,[95886],search_query: Could you identify any skin dise...
1,1,What drugs target the CYP3A4 enzyme and are us...,[15450],search_query: What drugs target the CYP3A4 enz...
2,2,What is the name of the condition characterize...,"[98851, 98853]",search_query: What is the name of the conditio...
3,3,What drugs are used to treat epithelioid sarco...,[15698],search_query: What drugs are used to treat epi...
4,4,Can you supply a compilation of genes and prot...,"[7161, 22045]",search_query: Can you supply a compilation of ...


In [15]:
# Since the records of queries has large amount of data, we will split them into mini-batches
mini_batch_size = 1000
query_embeddings = []
for i in tqdm(range(0, starkqa_df.shape[0], mini_batch_size)):
    outputs = emb_model.embed_documents(
        starkqa_df.query_prefixed.values.tolist()[i : i + mini_batch_size]
    )
    query_embeddings.extend(outputs)
query_embeddings

100%|██████████| 12/12 [00:06<00:00,  1.91it/s]


[array([ 1.3594e+00,  6.1426e-01, -3.1562e+00, -4.5361e-01,  1.0338e-02,
         4.9121e-01,  7.1045e-01, -7.2070e-01,  1.0557e+00, -1.7588e+00,
         5.0781e-01,  1.5537e+00,  1.7432e+00,  9.3311e-01, -7.3389e-01,
        -5.0391e-01, -4.1064e-01, -2.7393e-01,  2.5708e-01,  1.5244e+00,
        -1.5557e+00, -8.1982e-01,  5.3253e-02,  4.2480e-02,  8.8770e-01,
         1.2988e+00, -2.2400e-01,  4.9731e-01,  2.3828e-01, -2.3755e-01,
         1.4990e+00, -9.3018e-01,  6.9043e-01, -4.0112e-01,  1.6187e-01,
        -6.7871e-01,  7.0020e-01,  2.1680e-01,  6.7285e-01,  9.4971e-01,
         1.9434e+00,  3.1592e-01, -4.0210e-01, -9.8438e-01, -1.7383e-01,
         2.9639e-01,  7.9163e-02,  9.9316e-01,  1.7275e+00, -1.0303e+00,
         3.3765e-01,  4.0796e-01, -2.9736e-01, -1.0732e+00,  1.4395e+00,
        -9.7314e-01,  1.2285e+00, -2.9272e-01,  1.4668e+00,  8.4277e-01,
         1.7852e+00,  6.1035e-01, -7.9932e-01, -7.0679e-02,  1.3076e+00,
        -2.5391e-01,  2.5879e-01,  2.3657e-01,  2.4

In [16]:
# Check the shape of the query embeddings
len(query_embeddings), len(query_embeddings[0])

(11204, 768)

In [17]:
# Add them as features to the dataframe
starkqa_df["query_embedded"] = query_embeddings

# Drop and rename several columns
starkqa_df.drop(columns=["query_prefixed"], inplace=True)

# Check dataframe of nodes
starkqa_df.head()

,id,query,answer_ids,query_embedded
0,0,Could you identify any skin diseases associate...,[95886],"[1.359, 0.6143, -3.156, -0.4536, 0.01034, 0.49..."
1,1,What drugs target the CYP3A4 enzyme and are us...,[15450],"[0.6655, 0.1318, -3.799, 0.2302, 0.3062, -1.27..."
2,2,What is the name of the condition characterize...,"[98851, 98853]","[1.472, 0.7515, -2.807, -0.8774, -0.7383, 1.20..."
3,3,What drugs are used to treat epithelioid sarco...,[15698],"[-0.1757, 0.251, -2.768, 0.3882, 0.648, -0.344..."
4,4,Can you supply a compilation of genes and prot...,"[7161, 22045]","[0.6655, 1.371, -2.525, 0.02403, 0.937, -0.161..."


In [18]:
# Save the embedded queries dataframes to parquet file
starkqa_df.to_parquet(
    os.path.join(starkqa_data.local_dir, "starkqaprimekg_queries_embedded.parquet"),
    compression="gzip",
    index=False,
)

#### Node Embedding

Load the pre-processed embeddings, if available.

In [9]:
# # # Load the enriched nodes dataframe from parquet file
# primekg_nodes = pd.read_parquet(os.path.join(starkqa_data.local_dir, 'starkqaprimekg_nodes_embedded.parquet'), engine='pyarrow')

# # Check the dataframe of nodes, need to re-index the dataframe
# # Duplicate a node_name as index and use it as index
# primekg_nodes['node'] = primekg_nodes['node_id']
# primekg_nodes.set_index('node', inplace=True)
# primekg_nodes.head()

,node_id,node_name,node_type,enriched_node,x
node,,,,,
0,0,PHYHIP,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,"[0.3816, 0.602, -3.578, -0.8594, 1.287, -0.714..."
1,1,GPANK1,gene/protein,GPANK1 belongs to gene/protein category. This ...,"[0.1764, 0.4873, -2.969, -0.1147, 0.778, 1.202..."
2,2,ZRSR2,gene/protein,ZRSR2 belongs to gene/protein category. This g...,"[0.4622, 0.3542, -2.965, -0.2947, -0.0598, -0...."
3,3,NRF1,gene/protein,NRF1 belongs to gene/protein category. This ge...,"[0.2487, 0.907, -3.1, 0.2844, 0.885, -0.4102, ..."
4,4,PI4KA,gene/protein,PI4KA belongs to gene/protein category. This g...,"[0.663, 0.6875, -2.568, -0.198, 0.9404, -0.146..."


If there is no pre-processed node embeddings, run the following codes to generate embeddings.

Otherwise, skip the following cells and go to `Edge Embedding`.

In [19]:
# Prepend prefix to the enriched node
primekg_nodes["enriched_node_prefixed"] = primekg_nodes["enriched_node"].apply(
    lambda x: f"search_document: {x}"
)
primekg_nodes.head()

,node_index,node_name,node_source,node_id,node_type,enriched_node,enriched_node_prefixed
0,0,PHYHIP,NCBI,9796,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,search_document: PHYHIP belongs to gene/protei...
1,1,GPANK1,NCBI,7918,gene/protein,GPANK1 belongs to gene/protein category. This ...,search_document: GPANK1 belongs to gene/protei...
2,2,ZRSR2,NCBI,8233,gene/protein,ZRSR2 belongs to gene/protein category. This g...,search_document: ZRSR2 belongs to gene/protein...
3,3,NRF1,NCBI,4899,gene/protein,NRF1 belongs to gene/protein category. This ge...,search_document: NRF1 belongs to gene/protein ...
4,4,PI4KA,NCBI,5297,gene/protein,PI4KA belongs to gene/protein category. This g...,search_document: PI4KA belongs to gene/protein...


In [20]:
# Since the records of nodes has large amount of data, we will split them into mini-batches
mini_batch_size = 1000
node_embeddings = []
for i in tqdm(range(0, primekg_nodes.shape[0], mini_batch_size)):
    outputs = emb_model.embed_documents(
        primekg_nodes.enriched_node_prefixed.values.tolist()[i : i + mini_batch_size]
    )
    node_embeddings.extend(outputs)
node_embeddings

100%|██████████| 130/130 [02:13<00:00,  1.03s/it]


[array([ 3.8159e-01,  6.0205e-01, -3.5781e+00, -8.5938e-01,  1.2871e+00,
        -7.1387e-01, -5.0586e-01,  1.9995e-01, -7.4280e-02, -7.3828e-01,
         5.9521e-01,  5.9717e-01,  1.0547e+00, -6.2469e-02, -6.7432e-01,
        -9.6631e-01, -1.5283e-01, -4.7754e-01,  2.1472e-01,  1.1807e+00,
        -1.7676e+00, -6.8164e-01, -9.2346e-02,  1.3428e-01,  1.8242e+00,
         1.0332e+00,  8.5352e-01, -1.1729e+00,  1.4526e-01,  2.4487e-01,
        -3.5693e-01, -4.3774e-01,  5.0049e-01, -7.4561e-01,  7.1106e-02,
        -8.5059e-01,  1.1016e+00,  1.1041e-01,  2.8589e-01,  2.9834e-01,
        -1.0516e-01,  1.7786e-01, -3.1274e-01, -1.9104e-01,  3.6426e-01,
         3.5229e-01, -5.6885e-01,  7.7393e-02,  9.8926e-01, -6.0791e-01,
         8.4082e-01,  4.7314e-01, -2.0190e-01, -2.9590e-01,  2.4258e+00,
         3.5742e-01,  9.5752e-01,  2.5098e-01,  1.0645e+00,  6.5820e-01,
         2.1602e+00,  2.5293e+00, -8.2959e-01,  1.2754e+00,  1.4551e+00,
        -7.6172e-01, -2.4390e-01,  1.0771e+00, -1.0

In [21]:
# Check the shape of the node embeddings
len(node_embeddings), len(node_embeddings[0])

(129375, 768)

In [22]:
# Add them as features to the dataframe
primekg_nodes["x"] = node_embeddings

# Drop and rename several columns
primekg_nodes.drop(
    columns=["node_source", "node_id", "enriched_node_prefixed"], inplace=True
)
primekg_nodes.rename(columns={"node_index": "node_id"}, inplace=True)

# Check dataframe of nodes
primekg_nodes.head()

,node_id,node_name,node_type,enriched_node,x
0,0,PHYHIP,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,"[0.3816, 0.602, -3.578, -0.8594, 1.287, -0.714..."
1,1,GPANK1,gene/protein,GPANK1 belongs to gene/protein category. This ...,"[0.1764, 0.4873, -2.969, -0.1147, 0.778, 1.202..."
2,2,ZRSR2,gene/protein,ZRSR2 belongs to gene/protein category. This g...,"[0.4622, 0.3542, -2.965, -0.2947, -0.0598, -0...."
3,3,NRF1,gene/protein,NRF1 belongs to gene/protein category. This ge...,"[0.2487, 0.907, -3.1, 0.2844, 0.885, -0.4102, ..."
4,4,PI4KA,gene/protein,PI4KA belongs to gene/protein category. This g...,"[0.663, 0.6875, -2.568, -0.198, 0.9404, -0.146..."


In [23]:
# Duplicate a node_name as index and use it as index
primekg_nodes["node"] = primekg_nodes["node_id"]
primekg_nodes.set_index("node", inplace=True)
primekg_nodes.head()

,node_id,node_name,node_type,enriched_node,x
node,,,,,
0,0,PHYHIP,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,"[0.3816, 0.602, -3.578, -0.8594, 1.287, -0.714..."
1,1,GPANK1,gene/protein,GPANK1 belongs to gene/protein category. This ...,"[0.1764, 0.4873, -2.969, -0.1147, 0.778, 1.202..."
2,2,ZRSR2,gene/protein,ZRSR2 belongs to gene/protein category. This g...,"[0.4622, 0.3542, -2.965, -0.2947, -0.0598, -0...."
3,3,NRF1,gene/protein,NRF1 belongs to gene/protein category. This ge...,"[0.2487, 0.907, -3.1, 0.2844, 0.885, -0.4102, ..."
4,4,PI4KA,gene/protein,PI4KA belongs to gene/protein category. This g...,"[0.663, 0.6875, -2.568, -0.198, 0.9404, -0.146..."


In [24]:
# Save the embedded nodes dataframes to parquet file
primekg_nodes.to_parquet(
    os.path.join(starkqa_data.local_dir, "starkqaprimekg_nodes_embedded.parquet"),
    compression="gzip",
    index=False,
)

#### Edge Embedding

Load the pre-processed embeddings, if available.

In [10]:
# # Load the enriched edges dataframes from parquet file
# primekg_edges = pd.read_parquet(os.path.join(starkqa_data.local_dir, 'starkqaprimekg_edges_embedded.parquet'), engine='pyarrow')

# # Check the dataframe of edges
# primekg_edges.head()

,head_id,head_name,tail_id,tail_name,edge_type,enriched_edge,edge_attr
0,0,PHYHIP,8889,KIF15,ppi,PHYHIP (gene/protein) has a direct relationshi...,"[0.793, 1.01, -3.723, -0.01375, 0.77, -0.775, ..."
1,1,GPANK1,2798,PNMA1,ppi,GPANK1 (gene/protein) has a direct relationshi...,"[0.1575, 0.693, -3.031, 0.6606, 0.562, 0.5293,..."
2,2,ZRSR2,5646,TTC33,ppi,ZRSR2 (gene/protein) has a direct relationship...,"[0.5605, 0.634, -3.568, 0.1197, 0.01306, -0.47..."
3,3,NRF1,11592,MAN1B1,ppi,NRF1 (gene/protein) has a direct relationship ...,"[0.5034, 0.574, -3.402, 0.5264, 0.3987, 0.1387..."
4,4,PI4KA,2122,RGS20,ppi,PI4KA (gene/protein) has a direct relationship...,"[0.2964, 0.7344, -3.174, -0.1785, 0.643, -0.21..."


If there is no pre-processed node embeddings, run the following codes to generate embeddings.

Otherwise, skip the following cells.

In [25]:
# Prepend prefix to the enriched edge
primekg_edges["enriched_edge_prefixed"] = primekg_edges["enriched_edge"].apply(
    lambda x: f"search_document: {x}"
)
primekg_edges.head()

,head_index,head_name,head_source,head_id,head_type,tail_index,tail_name,tail_source,tail_id,tail_type,display_relation,relation,enriched_edge,enriched_edge_prefixed
0,0,PHYHIP,NCBI,9796,gene/protein,8889,KIF15,NCBI,56992,gene/protein,ppi,protein_protein,PHYHIP (gene/protein) has a direct relationshi...,search_document: PHYHIP (gene/protein) has a d...
1,1,GPANK1,NCBI,7918,gene/protein,2798,PNMA1,NCBI,9240,gene/protein,ppi,protein_protein,GPANK1 (gene/protein) has a direct relationshi...,search_document: GPANK1 (gene/protein) has a d...
2,2,ZRSR2,NCBI,8233,gene/protein,5646,TTC33,NCBI,23548,gene/protein,ppi,protein_protein,ZRSR2 (gene/protein) has a direct relationship...,search_document: ZRSR2 (gene/protein) has a di...
3,3,NRF1,NCBI,4899,gene/protein,11592,MAN1B1,NCBI,11253,gene/protein,ppi,protein_protein,NRF1 (gene/protein) has a direct relationship ...,search_document: NRF1 (gene/protein) has a dir...
4,4,PI4KA,NCBI,5297,gene/protein,2122,RGS20,NCBI,8601,gene/protein,ppi,protein_protein,PI4KA (gene/protein) has a direct relationship...,search_document: PI4KA (gene/protein) has a di...


In [26]:
# Since the records of edges has large amount of data, we will split them into mini-batches
mini_batch_size = 1000
edge_embeddings = []
for i in tqdm(range(0, primekg_edges.shape[0], mini_batch_size)):
    outputs = emb_model.embed_documents(
        primekg_edges.enriched_edge_prefixed.values.tolist()[i : i + mini_batch_size]
    )
    edge_embeddings.extend(outputs)
edge_embeddings

100%|██████████| 8101/8101 [1:12:32<00:00,  1.86it/s]


[array([ 7.9297e-01,  1.0098e+00, -3.7227e+00, -1.3748e-02,  7.7002e-01,
        -7.7490e-01, -1.1680e+00,  4.1779e-02,  1.9373e-01, -1.4160e+00,
         6.3379e-01,  4.7412e-01,  9.8096e-01, -1.7395e-02,  3.0151e-01,
        -5.0934e-02,  8.6230e-01, -7.9639e-01,  2.8125e-01,  1.4473e+00,
        -2.0508e+00, -4.8657e-01, -7.8564e-01,  2.2791e-01,  2.3887e+00,
         3.0908e-01, -2.2797e-02, -1.4365e+00, -5.3564e-01,  5.2490e-01,
         2.3340e-01, -2.9907e-01,  8.2275e-01, -1.3223e+00, -3.2935e-01,
        -1.1758e+00,  1.5283e+00,  4.3701e-01,  4.0747e-01,  6.3818e-01,
        -3.1567e-01,  6.3379e-01,  4.7363e-01, -1.0413e-01,  3.1519e-01,
        -1.0352e-01, -3.4741e-01,  1.9849e-01,  1.1377e+00, -8.1445e-01,
         3.5913e-01,  4.4287e-01, -1.4563e-01, -3.3813e-01,  1.6123e+00,
         8.5400e-01,  5.2393e-01,  2.8305e-03,  1.0967e+00,  4.2090e-01,
         2.0215e+00,  1.8994e+00, -6.4600e-01,  1.6348e+00,  1.8135e+00,
        -8.6328e-01, -4.2041e-01,  1.2080e+00, -7.2

In [27]:
# Check the shape of the edge embeddings
len(edge_embeddings), len(edge_embeddings[0])

(8100498, 768)

In [28]:
# Add them as features to the dataframe
primekg_edges["edge_attr"] = edge_embeddings

# Drop and rename several columns
primekg_edges.drop(
    columns=[
        "head_source",
        "head_id",
        "head_type",
        "tail_source",
        "tail_id",
        "tail_type",
        "relation",
        "enriched_edge_prefixed",
    ],
    inplace=True,
)
primekg_edges.rename(
    columns={
        "head_index": "head_id",
        "tail_index": "tail_id",
        "display_relation": "edge_type",
    },
    inplace=True,
)

# Check dataframe of edges
primekg_edges.head()

,head_id,head_name,tail_id,tail_name,edge_type,enriched_edge,edge_attr
0,0,PHYHIP,8889,KIF15,ppi,PHYHIP (gene/protein) has a direct relationshi...,"[0.793, 1.01, -3.723, -0.01375, 0.77, -0.775, ..."
1,1,GPANK1,2798,PNMA1,ppi,GPANK1 (gene/protein) has a direct relationshi...,"[0.1575, 0.693, -3.031, 0.6606, 0.562, 0.5293,..."
2,2,ZRSR2,5646,TTC33,ppi,ZRSR2 (gene/protein) has a direct relationship...,"[0.5605, 0.634, -3.568, 0.1197, 0.01306, -0.47..."
3,3,NRF1,11592,MAN1B1,ppi,NRF1 (gene/protein) has a direct relationship ...,"[0.5034, 0.574, -3.402, 0.5264, 0.3987, 0.1387..."
4,4,PI4KA,2122,RGS20,ppi,PI4KA (gene/protein) has a direct relationship...,"[0.2964, 0.7344, -3.174, -0.1785, 0.643, -0.21..."


In [29]:
# Save the embedded edges dataframes to parquet file
primekg_edges.to_parquet(
    os.path.join(starkqa_data.local_dir, "starkqaprimekg_edges_embedded.parquet"),
    compression="gzip",
    index=False,
)

### Knowledge Graph Construction

We would like to convert our dataframes to networkx `DiGraph` object.

In [11]:
# Convert dataframes to knowledge graph as networkx object
kg = kg_utils.df_pandas_to_kg(
    primekg_edges, primekg_nodes, node_source="head_id", node_target="tail_id"
)

In [12]:
# Save graph object
with open(os.path.join(starkqa_data.local_dir, "kg_nx_graph.pkl"), "wb") as f:
    pickle.dump(kg, f)

# # Load graph object
# with open(os.path.join(starkqa_data.local_dir, 'kg_nx_graph.pkl'), 'rb') as f:
#     kg = pickle.load(f)

In [13]:
print("#Nodes", kg.number_of_nodes())
print("#Edges", kg.number_of_edges())

#Nodes 129375
#Edges 8099284


We can convert the networkx graph to PyG `Data` object

In [14]:
# Convert networkx graph to PyG data object
pyg_graph = from_networkx(kg)

# Save graph object
with open(os.path.join(starkqa_data.local_dir, "kg_pyg_graph.pkl"), "wb") as f:
    pickle.dump(pyg_graph, f)

# Load graph object
# with open(os.path.join(starkqa_data.local_dir, 'kg_pyg_graph.pkl'), 'rb') as f:
#     pyg_graph = pickle.load(f)

/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/torch_geometric/utils/convert.py:278: UserWarning: Creating a tensor from a list of numpy.ndarrays is extremely slow. Please consider converting the list to a single numpy.ndarray with numpy.array() before converting to a tensor. (Triggered internally at ../torch/csrc/utils/tensor_new.cpp:278.)
  data_dict[key] = torch.as_tensor(value)


Lastly, we will also prepare a textualized graph of nodes and edges for RAG application, for instance.


In [15]:
# Prepare nodes
nodes_df = primekg_nodes.copy()
nodes_df.reset_index(drop=True, inplace=True)
nodes_df.drop(columns=["node_type", "x"], inplace=True)
nodes_df.rename(columns={"enriched_node": "node_attr"}, inplace=True)
nodes_df.head()

,node_id,node_name,node_attr
0,0,PHYHIP,PHYHIP belongs to gene/protein category. Enabl...
1,1,GPANK1,GPANK1 belongs to gene/protein category. This ...
2,2,ZRSR2,ZRSR2 belongs to gene/protein category. This g...
3,3,NRF1,NRF1 belongs to gene/protein category. This ge...
4,4,PI4KA,PI4KA belongs to gene/protein category. This g...


In [16]:
# Save it to parquet file
nodes_df.to_parquet(
    os.path.join(starkqa_data.local_dir, "kg_textualized_graph_nodes.parquet"),
    compression="gzip",
    index=False,
)

In [17]:
# Prepare edges
edges_df = primekg_edges.copy()
edges_df.drop(columns=["enriched_edge", "edge_attr"], inplace=True)
edges_df.head()

,head_id,head_name,tail_id,tail_name,edge_type
0,0,PHYHIP,8889,KIF15,ppi
1,1,GPANK1,2798,PNMA1,ppi
2,2,ZRSR2,5646,TTC33,ppi
3,3,NRF1,11592,MAN1B1,ppi
4,4,PI4KA,2122,RGS20,ppi


In [18]:
# Save it to parquet file
edges_df.to_parquet(
    os.path.join(starkqa_data.local_dir, "kg_textualized_graph_edges.parquet"),
    compression="gzip",
    index=False,
)